### Library Imports

In [1]:
!pip install tensorflow==2.11.0


[notice] A new release of pip is available: 23.0.1 -> 23.3.1
[notice] To update, run: python.exe -m pip install --upgrade pip


In [2]:
import numpy as np
import pandas as pd
import plotly.figure_factory as ff
import plotly.express as px
import plotly.io as pio
import plotly.graph_objects as go
import tensorflow as tf
from seaborn import load_dataset
from tensorflow.keras.models import Sequential
from tensorflow.keras.layers import Dense, Dropout
from tensorflow.keras.callbacks import EarlyStopping
from sklearn.linear_model import ElasticNet
from sklearn.preprocessing import StandardScaler

# pio.templates.default = "plotly_white"
# default_font_size = 36
# pio.templates["plotly_white"]["layout"].update(
#     {
#         "title_font": {"size": default_font_size},
#         "xaxis_title_font": {"size": default_font_size},
#         "yaxis_title_font": {"size": default_font_size},
#         "legend_font": {"size": default_font_size},
#     }
# )
# np.set_printoptions(precision=12, suppress=True, linewidth=150)
# pd.options.display.float_format = '{:.3f}'.format
tf.__version__

'2.11.0'

#### Load the synthetic EPA SWMM dataset from Excel into a pandas DataFrame

In [3]:
!pip install openpyxl


[notice] A new release of pip is available: 23.0.1 -> 23.3.1
[notice] To update, run: python.exe -m pip install --upgrade pip


In [49]:
raw_dataset = pd.read_excel('dataset.xlsx')
raw_dataset.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 103073 entries, 0 to 103072
Data columns (total 25 columns):
 #   Column         Non-Null Count   Dtype  
---  ------         --------------   -----  
 0   Unnamed: 0     103073 non-null  int64  
 1   Raingage       103073 non-null  int64  
 2   Outlet         103073 non-null  object 
 3   Area           103073 non-null  int64  
 4   PercImperv     103073 non-null  int64  
 5   Width          103073 non-null  int64  
 6   PercSlope      103073 non-null  int64  
 7   CurbLength     103073 non-null  int64  
 8   N-Imperv       103073 non-null  float64
 9   N-Perv         103073 non-null  float64
 10  S-Imperv       103073 non-null  float64
 11  S-Perv         103073 non-null  float64
 12  PctZero        103073 non-null  int64  
 13  RouteTo        103073 non-null  object 
 14  TotalPrecip    103073 non-null  int64  
 15  TotalRunon     103073 non-null  int64  
 16  TotalEvap      103073 non-null  int64  
 17  TotalInfil     103073 non-nul

#### Prepare a working copy of the dataset and inspect the first five records

In [111]:
dataset = raw_dataset.copy()
dataset.head()

,Unnamed: 0,Raingage,Outlet,Area,PercImperv,Width,PercSlope,CurbLength,N-Imperv,N-Perv,...,TotalRunon,TotalEvap,TotalInfil,ImpervRunoff,PervRunoff,TotalRunoffIn,TotalRunoffMG,PeakRunoff,RunoffCoeff,coords
0,0,1,J1,5,25,100,10,0,0.010,1.000,...,0,0,8.13,24.12,43.08,67.20,3.36,0.19,0.693,"[(777181.812, 592589.633), (777181.932, 592580..."
1,1,1,J1,5,1,1,1,0,0.015,0.015,...,0,0,12.04,0.93,20.20,21.13,1.06,0.07,0.218,"[(777181.812, 592589.633), (777181.932, 592580..."
2,2,1,J1,5,1,1,1,0,0.015,0.015,...,0,0,12.04,0.93,20.20,21.13,1.06,0.07,0.218,"[(777181.812, 592589.633), (777181.932, 592580..."
3,3,1,J1,5,1,1,1,0,0.015,0.015,...,0,0,12.04,0.93,20.20,21.13,1.06,0.07,0.218,"[(777181.812, 592589.633), (777181.932, 592580..."
4,4,1,J1,5,1,1,1,0,0.015,0.015,...,0,0,12.04,0.93,20.20,21.13,1.06,0.07,0.218,"[(777181.812, 592589.633), (777181.932, 592580..."


#### Drop redundant SWMM metadata and intermediate runoff columns

In [112]:
dataset.drop(["Unnamed: 0", 'Area', 'RouteTo', 'CurbLength', 'ImpervRunoff', 'PervRunoff', 'TotalInfil', 'PeakRunoff', 'coords', 'RunoffCoeff', 'TotalRunoffIn', 'TotalRunon', 'TotalEvap', "TotalPrecip", "Raingage", "Outlet", ], axis=1, inplace=True)
dataset.rename(columns={"TotalRunoffMG": "Runoff"}, inplace=True)
dataset.head()

,PercImperv,Width,PercSlope,N-Imperv,N-Perv,S-Imperv,S-Perv,PctZero,Runoff
0,25,100,10,0.010,1.000,0.05,0.05,25,3.36
1,1,1,1,0.015,0.015,0.05,0.05,1,1.06
2,1,1,1,0.015,0.015,0.05,0.05,10,1.06
3,1,1,1,0.015,0.015,0.05,0.05,20,1.06
4,1,1,1,0.015,0.015,0.05,0.05,40,1.06


#### Missing Value Audit per Column

In [52]:
dataset.isnull().sum() / len(dataset)

PercImperv    0.0
Width         0.0
PercSlope     0.0
N-Imperv      0.0
N-Perv        0.0
S-Imperv      0.0
S-Perv        0.0
PctZero       0.0
Runoff        0.0
dtype: float64

##### No missing values are present in the dataset

#### Dataset Schema: 8 Input Predictors and Target Variable (`Runoff`)

In [113]:
dataset.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 103073 entries, 0 to 103072
Data columns (total 9 columns):
 #   Column      Non-Null Count   Dtype  
---  ------      --------------   -----  
 0   PercImperv  103073 non-null  int64  
 1   Width       103073 non-null  int64  
 2   PercSlope   103073 non-null  int64  
 3   N-Imperv    103073 non-null  float64
 4   N-Perv      103073 non-null  float64
 5   S-Imperv    103073 non-null  float64
 6   S-Perv      103073 non-null  float64
 7   PctZero     103073 non-null  int64  
 8   Runoff      103073 non-null  float64
dtypes: float64(5), int64(4)
memory usage: 7.1 MB


## Optimize Column Data Types

In [114]:
# Optimize column data types
def change_dtypes(df: pd.DataFrame) -> pd.DataFrame:
    df["PercImperv"] = df["PercImperv"].astype("int8")
    df["Width"] = df["Width"].astype("int16")
    df["PercSlope"] = df["PercSlope"].astype("int8")
    df["N-Imperv"] = df["N-Imperv"].astype("float32")
    df["N-Perv"] = df["N-Perv"].astype("float32")
    df["S-Imperv"] = df["S-Imperv"].astype("float32")
    df["S-Perv"] = df["S-Perv"].astype("float32")
    df["PctZero"] = df["PctZero"].astype("int8")
    return df

In [115]:
dataset = change_dtypes(dataset)
dataset.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 103073 entries, 0 to 103072
Data columns (total 9 columns):
 #   Column      Non-Null Count   Dtype  
---  ------      --------------   -----  
 0   PercImperv  103073 non-null  int8   
 1   Width       103073 non-null  int16  
 2   PercSlope   103073 non-null  int8   
 3   N-Imperv    103073 non-null  float32
 4   N-Perv      103073 non-null  float32
 5   S-Imperv    103073 non-null  float32
 6   S-Perv      103073 non-null  float32
 7   PctZero     103073 non-null  int8   
 8   Runoff      103073 non-null  float64
dtypes: float32(4), float64(1), int16(1), int8(3)
memory usage: 2.9 MB


#### Descriptive Statistics of Raw Dataset

In [116]:
stats = dataset.describe()
# stats = stats.transpose()
stats
stats.to_excel("stats.xlsx")

Summary statistics across numeric columns:

* `count`: number of non-null observations
* `mean`: arithmetic mean
* `std`: sample standard deviation
* `min`: minimum value
* `25%`: first quartile (0.25 quantile)
* `50%`: median (0.50 quantile)
* `75%`: third quartile (0.75 quantile)
* `max`: maximum value

#### Distribution of Target Variable (`Runoff`)

In [117]:
fig = px.histogram(dataset, x='Runoff', width=1000, height=500)
fig.update_layout(
    title={'text': "Distribution of Target Variable (Runoff)", 'y': 0.9, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 36}},
    xaxis_title="Runoff [m3/s]",
    yaxis_title="Sample Count",
    xaxis=dict(title=dict(font=dict(size=36))),
    yaxis=dict(title=dict(font=dict(size=36))),
    font=dict(size=36)
)

#### Zero-runoff records originate from degenerate boundary combinations in the parametric sweep and are filtered out prior to modeling.

### Zero-Runoff Sample Count

In [118]:
dataset.Runoff.value_counts()

4.46    2247
4.49    2034
4.50    2016
4.53    1904
4.47    1864
        ... 
3.39       2
1.72       2
2.27       2
3.01       1
0.41       1
Name: Runoff, Length: 400, dtype: int64

#### Number of zero-runoff boundary records removed: 34,560

### Filter Out Zero-Runoff Records and Inspect Cleaned Target Distribution

In [119]:
index_to_drop = dataset[dataset.Runoff == 0].index
dataset = dataset.drop(index=index_to_drop)
fig = px.histogram(dataset, x='Runoff', width=1000, height=500)
fig.update_layout(
    title={'text': "Distribution of Target Variable (Runoff)", 'y': 0.9, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 36}},
    xaxis_title="Runoff [m3/s]",
    yaxis_title="Sample Count",
    xaxis=dict(title=dict(font=dict(size=36))),
    yaxis=dict(title=dict(font=dict(size=36))),
    font=dict(size=36)
)

### Descriptive Statistics of Cleaned Dataset (N = 103,073)

In [120]:
dataset.describe()

,PercImperv,Width,PercSlope,N-Imperv,N-Perv,S-Imperv,S-Perv,PctZero,Runoff
count,103073.000000,103073.000000,103073.000000,103073.000000,103073.000000,103073.000000,103073.000000,103073.000000,103073.000000
mean,42.902496,481.564445,42.807350,0.399142,0.402581,0.182513,0.182606,49.980907,3.670106
std,34.639448,359.301376,34.741852,0.319518,0.319632,0.102600,0.102590,35.066428,1.512434
min,1.000000,1.000000,1.000000,0.010000,0.015000,0.050000,0.050000,1.000000,0.030000
25%,10.000000,250.000000,10.000000,0.015000,0.015000,0.050000,0.050000,25.000000,3.710000
50%,40.000000,500.000000,40.000000,0.400000,0.400000,0.200000,0.200000,50.000000,4.400000
75%,80.000000,750.000000,80.000000,0.800000,0.800000,0.300000,0.300000,75.000000,4.560000
max,100.000000,1000.000000,100.000000,0.800000,1.000000,0.300000,0.300000,100.000000,4.850000


Summary statistics across numeric columns after filtering zero-runoff boundary cases:

* `count`: number of non-null observations (`103,073`)
* `mean`: arithmetic mean
* `std`: sample standard deviation
* `min`: minimum value
* `25%`: first quartile (0.25 quantile)
* `50%`: median (0.50 quantile)
* `75%`: third quartile (0.75 quantile)
* `max`: maximum value

In [121]:
fig = px.box(dataset, y='Runoff', width=300, height=600, title='Distribution of Target Variable (Runoff)')
fig.update_layout(
    title={'text': "Distribution of Target Variable (Runoff)", 'y': 0.9, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 12}},
    xaxis=dict(title=dict(font=dict(size=12))),
    yaxis=dict(title=dict(font=dict(size=12))),
    font=dict(size=12)
)
fig.show()

## Train / Test Split (80% / 20%)

In [122]:
train_dataset = dataset.sample(frac=0.8, random_state=0)
test_dataset = dataset.drop(train_dataset.index)

print(f'train_dataset length: {len(train_dataset)}')
print(f'test_dataset length: {len(test_dataset)}')

train_dataset length: 82458
test_dataset length: 20615


#### Training Set Descriptive Statistics Prior to Normalization (N = 82,458)

In [123]:
train_stats = train_dataset.describe()
train_stats.pop('Runoff')
train_stats = train_stats.transpose()
train_stats

,count,mean,std,min,25%,50%,75%,max
PercImperv,82458.0,42.851767,34.613555,1.000,10.000,40.0,80.0,100.0
Width,82458.0,481.575845,359.093807,1.000,250.000,500.0,750.0,1000.0
PercSlope,82458.0,42.760545,34.753151,1.000,10.000,40.0,80.0,100.0
N-Imperv,82458.0,0.399792,0.319596,0.010,0.015,0.4,0.8,0.8
N-Perv,82458.0,0.402409,0.319425,0.015,0.015,0.4,0.8,1.0
S-Imperv,82458.0,0.182457,0.102537,0.050,0.050,0.2,0.3,0.3
S-Perv,82458.0,0.182698,0.102496,0.050,0.050,0.2,0.3,0.3
PctZero,82458.0,50.014577,35.046184,1.000,25.000,50.0,75.0,100.0


In [124]:
# train_labels = train_dataset.pop('Runoff')
# test_labels = test_dataset.pop('Runoff')

y_train = train_dataset['Runoff']
y_test = test_dataset['Runoff']
X_train = train_dataset.drop('Runoff', axis=1)
X_test = test_dataset.drop('Runoff', axis=1)

## Feature Standardization (Z-Score Normalization Layer)

In [125]:
from tensorflow.keras.layers.experimental import preprocessing

normalizer = preprocessing.Normalization()
normalizer.adapt(X_train)

## Artificial Neural Network (ANN) Architecture

In [70]:
model = Sequential()
model.add(normalizer)
model.add(Dense(units=X_train.shape[1], activation="relu", input_shape=(X_train.shape[1],)))
model.add(Dense(units=8, activation="relu"))
model.add(Dense(units=8, activation="relu"))
model.add(Dense(units=1, activation="relu"))

In [71]:
model.compile(
    optimizer="adam",
    loss="mean_squared_error",
    metrics=["mae", "mse"]
)

### Model Architecture Summary

`model.summary()` reports the layer topology, output tensor shapes, and parameter counts for the sequential feedforward network:

* `normalization` (`Normalization`): Input Z-score standardization layer adapted to the 8 training predictors (`17` non-trainable state parameters).
* `dense` (`Dense`): First hidden layer with `8` units and ReLU activation (`72` trainable parameters).
* `dense_1` (`Dense`): Second hidden layer with `8` units and ReLU activation (`72` trainable parameters).
* `dense_2` (`Dense`): Third hidden layer with `8` units and ReLU activation (`72` trainable parameters).
* `dense_3` (`Dense`): Output regression unit (`1` neuron, ReLU activation for non-negative runoff; `9` trainable parameters).

Parameter totals:

* **Total params:** `234`
* **Trainable params:** `217`
* **Non-trainable params:** `17`

In [72]:
model.summary()

Model: "sequential_1"
_________________________________________________________________
 Layer (type)                Output Shape              Param #   
 normalization_1 (Normalizat  (None, 8)                17        
 ion)                                                            
                                                                 
 dense_4 (Dense)             (None, 8)                 72        
                                                                 
 dense_5 (Dense)             (None, 8)                 72        
                                                                 
 dense_6 (Dense)             (None, 8)                 72        
                                                                 
 dense_7 (Dense)             (None, 1)                 9         
                                                                 
Total params: 242
Trainable params: 225
Non-trainable params: 17
_______________________________________________________

## Model Training

In [73]:
history = model.fit(
    x=X_train,
    y=y_train.values,
    epochs=50,
    validation_split=0.2,
    verbose=1,
    callbacks=[EarlyStopping(monitor='val_loss', patience=2)],
    batch_size=32,
)

Epoch 1/50
2062/2062 [==============================] - 6s 2ms/step - loss: 1.1414 - mae: 0.6650 - mse: 1.1414 - val_loss: 0.1318 - val_mae: 0.2337 - val_mse: 0.1318
Epoch 2/50
2062/2062 [==============================] - 4s 2ms/step - loss: 0.1087 - mae: 0.2104 - mse: 0.1087 - val_loss: 0.0837 - val_mae: 0.1838 - val_mse: 0.0837
Epoch 3/50
2062/2062 [==============================] - 4s 2ms/step - loss: 0.0714 - mae: 0.1740 - mse: 0.0714 - val_loss: 0.0594 - val_mae: 0.1609 - val_mse: 0.0594
Epoch 4/50
2062/2062 [==============================] - 5s 2ms/step - loss: 0.0533 - mae: 0.1521 - mse: 0.0533 - val_loss: 0.0510 - val_mae: 0.1486 - val_mse: 0.0510
Epoch 5/50
2062/2062 [==============================] - 5s 2ms/step - loss: 0.0425 - mae: 0.1364 - mse: 0.0425 - val_loss: 0.0395 - val_mae: 0.1367 - val_mse: 0.0395
Epoch 6/50
2062/2062 [==============================] - 5s 2ms/step - loss: 0.0317 - mae: 0.1190 - mse: 0.0317 - val_loss: 0.0290 - val_mae: 0.1184 - val_mse: 0.0290
Epoc

### Training and Validation Loss Trajectory

In [74]:
hist = pd.DataFrame(history.history)
# print(hist['mae'].max())
print(hist['val_mae'].max())

0.2337324470281601


In [75]:
def plot_hist(history):
    hist = pd.DataFrame(history.history)
    hist['epoch'] = history.epoch
    hist['rmse'] = np.sqrt(hist['mse'])
    hist['val_rmse'] = np.sqrt(hist['val_mse'])

    fig = go.Figure()
    fig.add_trace(go.Scatter(x=hist['epoch'], y=hist['mae'], name='mae', mode='markers+lines'))
    fig.add_trace(go.Scatter(x=hist['epoch'], y=hist['val_mae'], name='val_mae', mode='markers+lines'))
    # fig.update_yaxes(dtick=0.2, tickformat='.2f', range=[-2, hist['mae'].max()])  # Ustawia podziałkę na 0.05
    fig.update_yaxes(dtick=0.2, tickformat='.2f',)  # Ustawia podziałkę na 0.05

    fig.update_layout(
        width=500, height=600, title='MAE vs. VAL_MAE', 
        xaxis_title='Epoki', yaxis_title='Mean Absolute Error', yaxis_type='log',
        title_font=dict(size=14), xaxis_title_font=dict(size=14), yaxis_title_font=dict(size=14)
    )
    fig.update_layout(
    title={'text': "MAE vs. VAL_MAE", 'y': 0.9, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 14}},
    xaxis_title="Epoki",
    yaxis_title="Mean Absolute Error",
    xaxis=dict(title=dict(font=dict(size=14))),
    yaxis=dict(title=dict(font=dict(size=14))),
    font=dict(size=14)
    )
    fig.show()

    fig = go.Figure()
    fig.add_trace(go.Scatter(x=hist['epoch'], y=hist['rmse'], name='rmse', mode='markers+lines'))
    fig.add_trace(go.Scatter(x=hist['epoch'], y=hist['val_rmse'], name='val_rmse', mode='markers+lines'))
    fig.update_yaxes(dtick=0.2, tickformat='.2f')  # Ustawia podziałkę na 0.05

    fig.update_layout(
        width=500, height=600, title='RMSE vs. VAL_RMSE', 
        xaxis_title='Epoki', yaxis_title='Root Mean Squared Error', yaxis_type='log',
        title_font=dict(size=14), xaxis_title_font=dict(size=14), yaxis_title_font=dict(size=14)
    )
    fig.update_layout(
    title={'text': "RMSE vs. VAL_RMSE", 'y': 0.9, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 14}},
    xaxis_title="Epoki",
    yaxis_title="Root Mean Squared Error",
    xaxis=dict(title=dict(font=dict(size=14))),
    yaxis=dict(title=dict(font=dict(size=14))),
    font=dict(size=14)
    )

    fig.show()

plot_hist(history)

### Test Set Evaluation Metrics (N = 20,615)

In [128]:
for name, value in zip(model.metrics_names, model.evaluate(X_test, y_test.values)):
    print(f'{name:8}{value:.4f}')

645/645 [==============================] - 1s 2ms/step - loss: 0.0118 - mae: 0.0748 - mse: 0.0118
loss    0.0118
mae     0.0748
mse     0.0118


### Generate 1-D Test Set Predictions (`ann_test_predictions`)

In [129]:
ann_test_predictions = model.predict(X_test).flatten()
ann_test_predictions

645/645 [==============================] - 1s 1ms/step


array([0.93832314, 0.9337982 , 0.901461  , ..., 4.818135  , 4.806708  ,
       4.803633  ], dtype=float32)

### Prediction Comparison Table

The `ann_pred` DataFrame pairs observed EPA SWMM runoff values against model predictions on the holdout test split:

* `Runoff`: ground-truth simulated surface runoff (`y_test`).
* `predictions`: ANN predicted surface runoff (`ann_test_predictions`).

In [130]:
ann_pred = pd.DataFrame(y_test)
ann_pred['predictions'] = ann_test_predictions
ann_pred.head()

,Runoff,predictions
2,1.06,0.938323
10,1.06,0.933798
13,1.06,0.901461
20,1.05,0.903192
21,1.05,0.892414


### Observed vs. Predicted Surface Runoff Scatter Plot

* **X-axis:** Observed EPA SWMM surface runoff (`Runoff` [$\text{m}^3/\text{s}$]).
* **Y-axis:** ANN predicted surface runoff (`predictions` [$\text{m}^3/\text{s}$]).

In [131]:
fig = px.scatter(ann_pred, 'Runoff', 'predictions')
fig.update_layout(
    title={'text': "Model Fit Plot", 'y': 0.95, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 20}},
    xaxis_title="Runoff",
    yaxis_title="Predictions",
    xaxis=dict(title=dict(font=dict(size=20))),
    yaxis=dict(title=dict(font=dict(size=20))),
    font=dict(size=20)
)
fig.add_trace(go.Scatter(x=[0, 5], y=[0, 5], mode='lines', name='Regression Line'))
fig.add_trace(go.Scatter(x=[None], y=[None], mode='markers', name='Actual vs Predicted', marker=dict(color='blue')))
fig.update_layout(width=800, height=500)
fig.update_layout(
    legend=dict(
        x=0.1,
        y=-0.15,
        traceorder='normal',
        orientation='h'
    )
)
fig.show()

### Sample Holdout Predictions vs. Ground Truth

In [132]:
ann_pred.head()

,Runoff,predictions
2,1.06,0.938323
10,1.06,0.933798
13,1.06,0.901461
20,1.05,0.903192
21,1.05,0.892414


### Prediction Residuals (`error`)

The `error` column records the residual (`Runoff - predictions`) for each test sample.

In [133]:
ann_pred['error'] = ann_pred['Runoff'] - ann_pred['predictions']
ann_pred.head()

,Runoff,predictions,error
2,1.06,0.938323,0.121677
10,1.06,0.933798,0.126202
13,1.06,0.901461,0.158539
20,1.05,0.903192,0.146808
21,1.05,0.892414,0.157586


### Residual Distribution Histogram

Distribution of prediction residuals (`Runoff - predictions`) across the `20,615` holdout test samples.

In [134]:
fig = px.histogram(ann_pred, 'error', marginal='rug', width=600, height=500)
fig.update_layout(
    title={'text': "Error Distribution Histogram", 'y': 0.95, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 20}},
    xaxis_title="Error",
    yaxis_title="Sample Count",
    xaxis=dict(title=dict(font=dict(size=20))),
    yaxis=dict(title=dict(font=dict(size=20))),
    font=dict(size=20)
)

In [138]:
from sklearn.metrics import mean_squared_error, r2_score
from scipy.stats import pearsonr

# Evaluate on holdout test set
ann_pred_test = model.predict(X_test).squeeze()

# Compute regression metrics
ann_mse_test = mean_squared_error(y_test, ann_pred_test)
ann_r2_test = r2_score(y_test, ann_pred_test)
rmse_test = np.sqrt(mean_squared_error(y_test, ann_pred_test))

# Calculate Index of Agreement
mean_observed = np.mean(y_test)
index_of_agreement = 1 - (np.sum((ann_pred_test - y_test) ** 2) / np.sum((np.abs(ann_pred_test - mean_observed) + np.abs(y_test - mean_observed)) ** 2))

# Calculate Scatter Index
scatter_index = np.sqrt(mean_squared_error(y_test, ann_pred_test)) / mean_observed


# Residual difference analysis
# errors_diff = np.abs(en_pred_test - ann_pred_test)
# cases_of_high_diff = np.where(errors_diff > threshold)  # Custom percentile threshold

# Measure batch inference latency
import time
start_time = time.time()
model.predict(X_test)
ann_inference_time = time.time() - start_time

print(f"ANN Test R2: {ann_r2_test:.3f}")
print(f"ANN Test MSE: {ann_mse_test:.3f}")
print(f"ANN Inference Time: {ann_inference_time:.3f}")
print(f"ANN Test RMSE: {rmse_test:.3f}")
print(f"ANN Index of Agreement: {index_of_agreement:.3f}")
print(f"ANN Scatter Index: {scatter_index:.3f}")


645/645 [==============================] - 1s 2ms/step
ANN Test R2: 0.995
ANN Test MSE: 0.012
ANN Inference Time: 1.344
ANN Test RMSE: 0.109
ANN Index of Agreement: 0.999
ANN Scatter Index: 0.030


# Conclusions

The feedforward Artificial Neural Network accurately approximates nonlinear EPA SWMM surface runoff dynamics across the 8-dimensional subcatchment parameter space (`R2 = 0.995`, `RMSE = 0.109 m3/s`, `MAE = 0.075 m3/s`, Index of Agreement `d = 0.999`, Scatter Index `SI = 0.030` on `N = 20,615` holdout test samples).

Compared with regularized linear regression (`ElasticNet`, `R2 = 0.550`, `RMSE = 1.017 m3/s`), the ANN resolves nonlinear interactions among imperviousness, overland flow width, slope, and surface roughness, at the cost of higher batch inference latency (`1.344 s` vs. `0.003 s` for `20,615` samples).

# Model Serialization and Comparative Error Analysis with Elastic Net

In [85]:
model.save("saved_model/swmm_ann_model")

INFO:tensorflow:Assets written to: saved_model/swmm_ann_model\assets


In [127]:
from tensorflow.keras.models import load_model

model = load_model("saved_model/swmm_ann_model")


In [37]:
# pred = model.predict(test_dataset).flatten()

In [139]:
train_dataset = dataset.sample(frac=0.8, random_state=0)
test_dataset = dataset.drop(train_dataset.index)

print(f'train_dataset length: {len(train_dataset)}')
print(f'test_dataset length: {len(test_dataset)}')

y_train = train_dataset['Runoff']
y_test = test_dataset['Runoff']
X_train = train_dataset.drop('Runoff', axis=1)
X_test = test_dataset.drop('Runoff', axis=1)

# Standardize features using Z-score scaling
scaler = StandardScaler()
scaler.fit(X_train)
X_train_scaled = scaler.transform(X_train)
X_test_scaled = scaler.transform(X_test)

train_dataset length: 82458
test_dataset length: 20615


In [140]:
# from sklearn.model_selection import GridSearchCV

# # Hyperparameter grid definition
# param_grid = {'alpha': [0.0001, 0.01, 0.1, 1, 10, 100], 'l1_ratio': [0.001, 0.1, 0.2, 0.4, 0.6, 0.8, 1]}

# # Initialize ElasticNet and 5-fold GridSearchCV
# elastic_net = ElasticNet(random_state=0)
# grid_search = GridSearchCV(elastic_net, param_grid, cv=5)

# # Fit GridSearchCV on standardized training data
# grid_search.fit(X_train_scaled, y_train)

# # Extract optimal hyperparameters
# best_params = grid_search.best_params_
# print("Best parameters: ", best_params)

model = ElasticNet(random_state=0, alpha=0.01, l1_ratio=0.2)
model.fit(X_train_scaled, y_train)
# # predictions = model.predict(X_test)
# # predictions

# # Evaluate best estimator
# best_model = grid_search.best_estimator_
# test_predictions = best_model.predict(X_test_scaled).flatten()

ElasticNet(alpha=0.01, l1_ratio=0.2, random_state=0)

In [141]:
en_test_predictions = model.predict(X_test_scaled).flatten()

en_pred = pd.DataFrame(y_test)
en_pred['predictions'] = en_test_predictions

fig = px.scatter(en_pred, 'Runoff', 'predictions')
fig.add_trace(go.Scatter(x=[0, 5], y=[0, 5], mode='lines', name='Regression Line'))
fig.update_layout(width=800, height=500)
fig.update_layout(
    title={'text': "Dane przewidywane", 'y': 0.9, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 18}},
    xaxis_title="Runoff",
    yaxis_title="Predictions",
    xaxis=dict(title=dict(font=dict(size=18))),
    yaxis=dict(title=dict(font=dict(size=18))),
    font=dict(size=18)
)
fig.show()

In [142]:
en_pred['error'] = en_pred['Runoff'] - en_pred['predictions']
fig = px.histogram(en_pred, 'error', marginal='rug')
fig.update_layout(
    title={'text': "Histogram of the error distribution", 'y': 0.9, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 18}},
    xaxis_title="Error",
    yaxis_title="Count of samples",
    xaxis=dict(title=dict(font=dict(size=18))),
    yaxis=dict(title=dict(font=dict(size=18))),
    font=dict(size=18)
)

In [152]:
from sklearn.metrics import mean_squared_error, r2_score
from scipy.stats import pearsonr

# Evaluate on holdout test set
en_pred_test = model.predict(X_test_scaled)

# Compute regression metrics
en_mse_test = mean_squared_error(y_test, en_pred_test)
en_r2_test = r2_score(y_test, en_pred_test)
en_rmse_test = np.sqrt(en_mse_test)

# Calculate Index of Agreement
en_mean_observed = np.mean(y_test)
en_index_of_agreement = 1 - (np.sum((en_pred_test - y_test) ** 2) / np.sum((np.abs(en_pred_test - en_mean_observed) + np.abs(y_test - en_mean_observed)) ** 2))

# Calculate Scatter Index
en_scatter_index = np.sqrt(mean_squared_error(y_test, en_pred_test)) / en_mean_observed
# Measure batch inference latency
import time
start_time = time.time()
model.predict(X_test_scaled)
en_inference_time = time.time() - start_time

print(f"ElasticNet Test R2: {en_r2_test:.3f}.")
print(f"ElasticNet Test MSE: {en_mse_test:.3f}.")
print(f"ElasticNet Inference Time: {en_inference_time:.3f}.")
print(f"ElasticNet Test RMSE: {en_rmse_test:.3f}")
print(f"ElasticNet Index of Agreement: {en_index_of_agreement:.3f}")
print(f"ElasticNet Scatter Index: {en_scatter_index:.3f}")

ElasticNet Test R2: 0.550.
ElasticNet Test MSE: 1.035.
ElasticNet Inference Time: 0.003.
ElasticNet Test RMSE: 1.017
ElasticNet Index of Agreement: 0.837
ElasticNet Scatter Index: 0.277


In [144]:
# Residual difference analysis
errors_diff = np.abs(en_pred_test - ann_pred_test)
threshold = np.percentile(errors_diff, 85)
cases_of_high_diff = np.where(errors_diff > threshold)
print(errors_diff)
print(cases_of_high_diff)

[1.1889731  1.1997234  1.2469479  ... 0.6356077  0.6520643  0.66134214]
(array([  24,   25,   26, ..., 7555, 7556, 7640], dtype=int64),)


In [145]:
from plotly.subplots import make_subplots
# Initialize subplots
fig = make_subplots(rows=1, cols=2, subplot_titles=("Histogram of Models Error Differences", "Point Plot of Models Error Differences"))
fig.update_annotations(dict(font=dict(size=20)))

# Add histogram to the first subplot
fig.add_trace(go.Histogram(x=errors_diff, name='Error Differences'), row=1, col=1)
fig.add_shape(dict(type='line', x0=threshold, x1=threshold, y0=0, y1=850, line=dict(color='red', width=3)), row=1, col=1)
fig.add_trace(go.Scatter(x=[None], y=[None], mode='lines', name='Threshold', line=dict(color='red', width=2)), row=1, col=2)

# Add scatter plot to the second subplot
fig.add_trace(go.Scatter(x=np.arange(len(errors_diff)), y=errors_diff, mode='markers', name='Below Threshold', marker=dict(color='rgba(99,110,250,255)', line=dict(width=0.5))), row=1, col=2)
fig.add_trace(go.Scatter(x=np.array(cases_of_high_diff[0]), y=errors_diff[cases_of_high_diff], mode='markers', marker=dict(color='red', line=dict(width=0.5)), name='Above Threshold'), row=1, col=2)
fig.add_shape(dict(type='line', x0=0, x1=len(errors_diff), y0=threshold, y1=threshold, line=dict(color='red', width=2)), row=1, col=2)


# Update layout
fig.update_layout(
    font=dict(size=20),
    width=1200,
    height=500
)

# Update axes for the first subplot
fig.update_xaxes(title_text="Error Difference [m3/s]", row=1, col=1, title_font=dict(size=20))
fig.update_yaxes(title_text="Frequency", row=1, col=1, title_font=dict(size=20))

# Update axes for the second subplot
fig.update_xaxes(title_text="Index Number", row=1, col=2, title_font=dict(size=20))
fig.update_yaxes(title_text="Error Difference [m3/s]", row=1, col=2, title_font=dict(size=20))

# Update legend
fig.update_layout(
    legend=dict(
        x=0.1,
        y=-0.22,
        traceorder='normal',
        orientation='h'
    )
)
fig.show()


In [146]:
import pandas as pd

# Assuming `errors_diff` and `threshold` are available as variables
# errors_diff = np.abs(en_pred_test - ann_pred_test)
# threshold = np.percentile(errors_diff, 85)

# Create a dictionary to store the metrics
metrics_dict = {
    'Mean Error Difference': [errors_diff.mean()],
    'Standard Deviation': [errors_diff.std()],
    'Min Error Difference': [errors_diff.min()],
    'Max Error Difference': [errors_diff.max()],
    'Threshold (85 percentile)': [threshold],
    'Number of Cases Above Threshold': [len(errors_diff[errors_diff > threshold])],
    'Percentage of Cases Above Threshold': [(len(errors_diff[errors_diff > threshold]) / len(errors_diff)) * 100]
}

# Convert dictionary to a DataFrame
metrics_df = pd.DataFrame(metrics_dict)

# Save the DataFrame to an Excel file
metrics_df.to_excel('error_analysis_metrics.xlsx', index=False)


In [147]:
from plotly.subplots import make_subplots
# Initialize side-by-side comparison subplots
fig = make_subplots(rows=1, cols=2, subplot_titles=("ANN Model", "ElasticNet Model"))
fig.update_annotations(dict(font=dict(size=20)))

# Add ANN observed vs. predicted scatter trace
fig.add_trace(go.Scatter(x=ann_pred['Runoff'], y=ann_pred['predictions'], mode='markers', name="Actual vs Predicted", marker=dict(line=dict(width=0.5))), row=1, col=1)
fig.add_trace(go.Scatter(x=[0, 5], y=[0, 5], mode='lines', name='Regression Line'), row=1, col=1)

# Add ElasticNet observed vs. predicted scatter trace
fig.add_trace(go.Scatter(x=en_pred["Runoff"], y=en_pred["predictions"], mode='markers', name="Actual vs Predicted", marker=dict(line=dict(width=0.5))), row=1, col=2)
fig.add_trace(go.Scatter(x=[0, 5], y=[0, 5], mode='lines', name='Regression Line'), row=1, col=2)

# Configure figure layout
fig.update_layout(
    # title={'text': "Model Fit Plots", 'y': 0.95, 'x': 0.5, 'xanchor': 'center', 'yanchor': 'top', 'font': {'size': 20}},
    font=dict(size=20),
    width=1200,
    height=500
)

# Configure axes for first subplot
fig.update_xaxes(title_text="Runoff [m3/s]", row=1, col=1, title_font=dict(size=20))
fig.update_yaxes(title_text="Predictions [m3/s]", row=1, col=1, title_font=dict(size=20))

# Configure axes for second subplot
fig.update_xaxes(title_text="Runoff [m3/s]", row=1, col=2, title_font=dict(size=20))
fig.update_yaxes(title_text="Predictions [m3/s]", row=1, col=2, title_font=dict(size=20))

# Configure horizontal legend
fig.update_layout(
    legend=dict(
        x=0.0,
        y=-0.22,
        traceorder='normal',
        orientation='h'
    )
)
fig.show()

In [148]:
from plotly.subplots import make_subplots

# Initialize side-by-side comparison subplots
fig = make_subplots(rows=1, cols=2)
fig.update_annotations(dict(font=dict(size=20)))
# Add ANN residual histogram to first subplot
fig.add_trace(go.Histogram(x=ann_pred['error'], name="Error Distribution ANN"), row=1, col=1)

# Add ElasticNet residual histogram to second subplot
fig.add_trace(go.Histogram(x=en_pred['error'], name="Error Distribution ElasticNet"), row=1, col=2)

# Configure figure layout
fig.update_layout(
    font=dict(size=20),
    width=1200,
    height=500
)

# Configure axes for first subplot
fig.update_xaxes(title_text="Error [m3/s]", row=1, col=1, title_font=dict(size=20))
fig.update_yaxes(title_text="Count of samples", row=1, col=1, title_font=dict(size=20))

# Configure axes for second subplot
fig.update_xaxes(title_text="Error [m3/s]", row=1, col=2, title_font=dict(size=20))
fig.update_yaxes(title_text="Count of samples", row=1, col=2, title_font=dict(size=20))

# Configure horizontal legend
fig.update_layout(
    legend=dict(
        x=0.0,
        y=-0.22,
        traceorder='normal',
        orientation='h'
    )
)
fig.show()


In [149]:
import numpy as np
import pandas as pd

# Extract residual arrays for ANN and ElasticNet
errors_ann = np.array(ann_pred['error'])
errors_en = np.array(en_pred['error'])

# Compute summary statistics and percentiles of prediction residuals
metrics_ann = {
    'mean': np.mean(errors_ann),
    'median': np.median(errors_ann),
    'std_dev': np.std(errors_ann),
    '5th_percentile': np.percentile(errors_ann, 5),
    '25th_percentile': np.percentile(errors_ann, 25),
    '75th_percentile': np.percentile(errors_ann, 75),
    '95th_percentile': np.percentile(errors_ann, 95)
}

metrics_en = {
    'mean': np.mean(errors_en),
    'median': np.median(errors_en),
    'std_dev': np.std(errors_en),
    '5th_percentile': np.percentile(errors_en, 5),
    '25th_percentile': np.percentile(errors_en, 25),
    '75th_percentile': np.percentile(errors_en, 75),
    '95th_percentile': np.percentile(errors_en, 95)
}

# Export comparative residual statistics to Excel
df_metrics = pd.DataFrame({'ANN': metrics_ann, 'ElasticNet': metrics_en})
df_metrics.to_excel("models_stats.xlsx")